collect human prs from the same ia eligible pr repos

In [13]:
# Extract ai eligible pr repositories
import pandas as pd
human_eligible_prs_raw = pd.read_json('../datasets/raw/eligible_human_pop_prs_metadata.jsonl',lines=True)
ai_eligible_prs = pd.read_csv('../datasets/processed/ai_eligible_prs.csv')

# Validate fetched data

## check repos

- same eligible pr repos


In [14]:
ai_eligible_prs_repos = ai_eligible_prs['repo_url'].drop_duplicates().str.replace('https://api.github.com/repos/','')
human_eligible_prs_repos = human_eligible_prs_raw['repo'].drop_duplicates()
print(f'ai eligible pop repos {len(ai_eligible_prs_repos)}')
print(f'human eligible pop repos {len(human_eligible_prs_repos)}')
not_scanned_repos = ai_eligible_prs_repos[~ai_eligible_prs_repos.isin(human_eligible_prs_repos)]
print(f'not scanned repos {len(not_scanned_repos)}')
not_scanned_repos



ai eligible pop repos 256
human eligible pop repos 116
not scanned repos 149


1                umputun/spot
3      JessicaTegner/pypandoc
7         vexxhost/atmosphere
10        czlonkowski/n8n-mcp
11         ruvnet/claude-flow
                ...          
876                azu/ni.zsh
898     michaellatman/mcp-get
901        magiclabs/magic-js
930                box/boxcli
960     confident-ai/deepteam
Name: repo_url, Length: 149, dtype: str

In [15]:
mixed_repos= pd.DataFrame(human_eligible_prs_repos)
mixed_repos['repo'] = 'https://api.github.com/repos/' + mixed_repos['repo']
mixed_repos

,repo
0,https://api.github.com/repos/3rdIteration/btcr...
1,https://api.github.com/repos/AMICI-dev/AMICI
6,https://api.github.com/repos/567-labs/instructor
12,https://api.github.com/repos/AgentOps-AI/agentops
17,https://api.github.com/repos/DannyMac180/meta-...
...,...
919,https://api.github.com/repos/wei/socialify
926,https://api.github.com/repos/whitphx/stlite
980,https://api.github.com/repos/wolfSSL/wolfssh
984,https://api.github.com/repos/wvlet/wvlet


In [16]:
good_ai_prs = ai_eligible_prs[
    ai_eligible_prs['repo_url'].isin(mixed_repos['repo'])
]

good_repos = good_ai_prs[['repo_url']].drop_duplicates()
good_repos


,repo_url
0,https://api.github.com/repos/mlflow/mlflow
2,https://api.github.com/repos/nrwl/nx
4,https://api.github.com/repos/modelcontextproto...
5,https://api.github.com/repos/sugyan/claude-cod...
13,https://api.github.com/repos/giselles-ai/giselle
...,...
917,https://api.github.com/repos/ensdomains/ens-ap...
939,https://api.github.com/repos/saturday06/VRM-Ad...
949,https://api.github.com/repos/kiwicom/orbit
958,https://api.github.com/repos/vlm-run/vlmrun-hub


- there are 93 repos are not scanned why?
after investigation, I found that , my script skipped these repos due to
1- they don't have prs with workflow files in first commit in the frame date
2- their prs are created after cut of date (22,jun,2025) like in jul, on the AIDev
this is why they exist in the ai eligible prs but my script didn't scan them
- it seems that the AIDev authors exceed the cut of date

In [17]:
ai_eligible_prs[ai_eligible_prs['repo_url'].str.contains('ruvnet/claude-flow')]

,pr_id,number,title,body,agent,user_id,user,state,created_at,closed_at,merged_at,repo_id,repo_url,html_url,first_commit_sha
11,3230351703,267,fix: CI/CD test failures and establish working...,## Summary\n- Fixed CI/CD test failures by est...,Claude_Code,2934394,ruvnet,closed,2025-07-15T00:16:41Z,2025-07-15T04:20:46Z,NaN,995029641,https://api.github.com/repos/ruvnet/claude-flow,https://github.com/ruvnet/claude-flow/pull/267,b480b0dca7559f72c3a466d6e7d9d090cd6ae6bd


## Validate prs

In [18]:
print(len(ai_eligible_prs))
print(len(human_eligible_prs_raw))
#check if human prs include any ai pr, result must be 0
ai_eligible_prs[ai_eligible_prs['html_url'].isin(human_eligible_prs_raw['pr_url'])]

966
1028


,pr_id,number,title,body,agent,user_id,user,state,created_at,closed_at,merged_at,repo_id,repo_url,html_url,first_commit_sha


# Extract human pr info

In [19]:
human_pr = human_eligible_prs_raw[['pr_url','pr','first_commit_sha','first_commit_workflow_files']]

human_pr_info = pd.json_normalize(human_pr['pr'])

human_pr = pd.concat([human_pr,human_pr_info],axis=1)
human_pr=human_pr[['html_url','first_commit_sha','state','locked','title','user.login','user.type','body','created_at','updated_at','closed_at','merged_at','merged','comments','review_comments','commits','additions','deletions','changed_files']]


# Filtered PRs 

## remove prs authored by ai

In [20]:
# (Removed exploration cell.) PRs with agent-style branch names or 'Co-Authored-By' AI
# lines are NOT removed from the human set: they are not fully AI-authored and the
# proportion of AI-authored code in them is unclear (see paper, Data Filtering).


## drop bot PRs and open state PRs

In [21]:
human_pr=human_pr[human_pr['user.type']=='User']
human_pr = human_pr[~human_pr['user.login'].str.contains('bot', na=False)]
human_pr = human_pr[~human_pr['user.login'].str.contains('copilot', na=False)]
human_pr = human_pr[human_pr['state']=='closed']
human_pr


,html_url,first_commit_sha,state,locked,title,user.login,user.type,body,created_at,updated_at,closed_at,merged_at,merged,comments,review_comments,commits,additions,deletions,changed_files
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,closed,False,Switch scrypt to wallycore,3rdIteration,User,## Summary\n- prefer `wallycore.scrypt` in `li...,2025-07-30T01:21:27Z,2025-07-30T02:27:25Z,2025-07-30T02:27:22Z,2025-07-30T02:27:22Z,True,0,0,2,49,7,6
1,https://github.com/AMICI-dev/AMICI/pull/2825,c1ee0cf6cb2fc7e9699c89f2743720e6878833e9,closed,False,"Fix uninitialized values, update valgrind supp...",dweindl,User,Fixes current valgrind-reported issues.,2025-06-26T07:08:40Z,2025-09-24T10:00:09Z,2025-06-26T09:37:21Z,2025-06-26T09:37:21Z,True,1,0,1,31,7,3
2,https://github.com/AMICI-dev/AMICI/pull/2820,8a8fee87790a2393dbd31f7d763336d3e6dd57a8,closed,False,GHA: develop -> main,dweindl,User,Fix some missed references to the discontinued...,2025-06-25T12:54:06Z,2025-09-23T13:30:29Z,2025-06-25T13:19:58Z,2025-06-25T13:19:58Z,True,1,0,1,2,2,2
3,https://github.com/AMICI-dev/AMICI/pull/2819,809119384d0777c42c3465cfee21777d087f57e3,closed,False,GHA: Fix libsbml crashes,dweindl,User,"On Python3.11, to prevent crashes, don't use `...",2025-06-25T12:17:30Z,2025-09-23T13:30:09Z,2025-06-25T13:03:10Z,2025-06-25T13:03:10Z,True,1,0,1,5,0,1
4,https://github.com/AMICI-dev/AMICI/pull/2818,e8f4526b12823795103ee6cb472deeaec624caac,closed,False,GHA: build docs on ubuntu 24.04,dweindl,User,* Use Ubuntu 24.04 for documentation tests\r\n...,2025-06-24T06:28:47Z,2025-09-22T08:30:09Z,2025-06-24T08:06:10Z,2025-06-24T08:06:10Z,True,1,0,2,4,4,2
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
1023,https://github.com/trycompai/comp/pull/130,e467fb36abca8c853208d29b0e209af54c323ea9,closed,False,Auto translate english,Marfuen,User,\n\n<!-- This is an auto-generated comment: re...,2025-03-13T17:31:42Z,2025-03-13T17:34:01Z,2025-03-13T17:32:13Z,2025-03-13T17:32:13Z,True,2,0,1,42,0,1
1024,https://github.com/trycompai/comp/pull/118,c7c2ad2a547a12a9594525a1de2e680826820a0d,closed,False,point gh action to correct folder,Marfuen,User,\n\n<!-- This is an auto-generated comment: re...,2025-03-07T18:23:30Z,2025-03-07T18:24:53Z,2025-03-07T18:23:39Z,2025-03-07T18:23:39Z,True,2,0,1,1,0,1
1025,https://github.com/trycompai/comp/pull/116,b46d1388f624e489ead0046acab0a714e7ed8361,closed,False,refactor: update Trigger.dev configuration and...,Marfuen,User,- Update trigger configs to include new trigge...,2025-03-07T14:56:01Z,2025-03-07T14:57:37Z,2025-03-07T14:57:09Z,2025-03-07T14:57:08Z,True,2,0,1,89,44,6
1026,https://github.com/trycompai/comp/pull/113,70502f4a90a4d2012756f9695e3bffd7bd021bba,closed,False,fix deploy script,Marfuen,User,NaN,2025-03-06T20:08:07Z,2025-03-06T20:08:14Z,2025-03-06T20:08:12Z,2025-03-06T20:08:11Z,True,2,0,1,1,2,1


In [22]:
# keep only non-bot prs in raw data
human_eligible_prs_raw = human_eligible_prs_raw.copy()[human_eligible_prs_raw['pr_url'].isin(human_pr['html_url'])]
print(len(human_eligible_prs_raw))
human_eligible_prs_raw[['commit_details']]

863


,commit_details
0,[{'sha': '691c8c1b32f12244ea378ee0018e9f136ed4...
1,[{'sha': 'c1ee0cf6cb2fc7e9699c89f2743720e68788...
2,[{'sha': '8a8fee87790a2393dbd31f7d763336d3e6dd...
3,[{'sha': '809119384d0777c42c3465cfee21777d087f...
4,[{'sha': 'e8f4526b12823795103ee6cb472deeaec624...
...,...
1023,[{'sha': 'e467fb36abca8c853208d29b0e209af54c32...
1024,[{'sha': 'c7c2ad2a547a12a9594525a1de2e68082682...
1025,[{'sha': 'b46d1388f624e489ead0046acab0a714e7ed...
1026,[{'sha': '70502f4a90a4d2012756f9695e3bffd7bd02...


## use commit details to detect empty commits

In [23]:
# human_commit_details_json = pd.read_json('outputs/eligible_human_pop_commit_details_metadata.jsonl',lines=True)
human_commit_details_json = human_eligible_prs_raw[['pr_url','first_commit_sha','commit_details']]
human_commit_details_json

human_commit_details_json_exploded = human_commit_details_json.explode(column=['commit_details'])
human_commit_details_normalized = pd.json_normalize(human_commit_details_json_exploded['commit_details'])
human_commit_details_concat = pd.concat([human_commit_details_json_exploded[['pr_url']],human_commit_details_normalized],axis=1)
human_commit_details_concat

human_commit_details_files_explode = human_commit_details_concat.explode('files').dropna(subset='files')
human_commit_details_files_normalized = pd.json_normalize(human_commit_details_files_explode['files'],max_level=0)
human_commit_details_files = pd.concat([human_commit_details_files_explode[['pr_url','sha']],human_commit_details_files_normalized[['filename','status','additions','deletions','changes','patch']]],axis=1)

# human_commit_details_files.to_csv('data/human_eligible_commit_details.csv')
human_commit_details_files 

,pr_url,sha,filename,status,additions,deletions,changes,patch
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,.github/workflows/Weekly-Run-All-Tests-Full.yml,modified,1,1,2,"@@ -37,7 +37,7 @@ jobs:\n run: |\n ..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,.github/workflows/Weekly-Run-All-Tests_Base.yml,modified,1,1,2,"@@ -34,7 +34,7 @@ jobs:\n run: |\n ..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,.github/workflows/termux-tests.yml,modified,2,2,4,"@@ -49,7 +49,7 @@ jobs:\n run: chown -..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,docs/INSTALL.md,modified,9,1,10,"@@ -203,7 +203,15 @@ Locate your wallet type i..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,lib/pylibscrypt/__init__.py,modified,29,2,31,"@@ -16,15 +16,42 @@\n \n __version__ = '2.0.0-..."
...,...,...,...,...,...,...,...,...
1027,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,.github/workflows/trigger-tasks-deploy.yml,added,32,0,32,"@@ -0,0 +1,32 @@\n+name: Deploy to Trigger.dev..."
1027,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/package.json,modified,3,2,5,"@@ -7,7 +7,8 @@\n ""build"": ""next build"",\n..."
1027,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/src/jobs/tasks/deel/index.ts,renamed,0,0,0,NaN
1027,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/src/jobs/tasks/deel/schedule.ts,renamed,0,0,0,NaN


## exclude empty first commit

In [24]:
human_commit_details_files[
    (human_commit_details_files['patch'].isna()) &
    (human_commit_details_files['filename'].str.startswith('.github/workflows'))&
    (human_commit_details_files['filename'].str.endswith(('.yaml', '.yml')))
]

,pr_url,sha,filename,status,additions,deletions,changes,patch
240,https://github.com/cloudwalk/stratus/pull/2079,ef0c32727b55ebdd956f539a3eb24c68ba08f2f6,.github/workflows/build-pgo.yml,renamed,0,0,0,NaN
750,https://github.com/roeniss/dhlottery-api/pull/150,71d8fa3a7c38b9b98598d07705eed29c471a4805,.github/workflows/lintFmtCheck.yml,renamed,0,0,0,NaN
751,https://github.com/roeniss/dhlottery-api/pull/152,7db6e990bb041488e598b45a489b6d3db7934535,.github/workflows/build-publish-release-note.yml,renamed,0,0,0,NaN
880,https://github.com/theopenco/llmgateway/pull/88,045a51ff1d799fdfc771441b5afd7b1d0d7e28a7,.github/workflows/images.yml,renamed,0,0,0,NaN
944,https://github.com/whitphx/stlite/pull/1375,cacdccfce20db6c10c075d920d7790cbbafb61de,.github/workflows/postbuild.yml,renamed,0,0,0,NaN
944,https://github.com/whitphx/stlite/pull/1375,cacdccfce20db6c10c075d920d7790cbbafb61de,.github/workflows/test-build.yml,renamed,0,0,0,NaN


In [25]:
empty_commits = human_commit_details_files[
    (human_commit_details_files['patch'].isna())
]
empty_commits

,pr_url,sha,filename,status,additions,deletions,changes,patch
7,https://github.com/AMICI-dev/AMICI/pull/2839,6487135846868ac9d13aad793911ed0066a2672a,doc/examples/example_steady_states/ExampleEqui...,modified,761,892,1653,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,6487135846868ac9d13aad793911ed0066a2672a,doc/examples/example_steady_states/figures/pre...,added,5366,0,5366,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,6487135846868ac9d13aad793911ed0066a2672a,doc/examples/getting_started_extended/GettingS...,modified,176,805,981,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,6487135846868ac9d13aad793911ed0066a2672a,doc/gfx/amici_workflow.png,modified,0,0,0,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,6487135846868ac9d13aad793911ed0066a2672a,doc/gfx/amici_workflow.svg,modified,1385,1305,2690,NaN
...,...,...,...,...,...,...,...,...
1021,https://github.com/trycompai/comp/pull/232,505364ccd33592763d599c91912d2e31ce55724d,apps/app/src/app/[locale]/(app)/(dashboard)/[o...,renamed,0,0,0,NaN
1021,https://github.com/trycompai/comp/pull/232,505364ccd33592763d599c91912d2e31ce55724d,apps/app/src/app/[locale]/(app)/(dashboard)/[o...,renamed,0,0,0,NaN
1021,https://github.com/trycompai/comp/pull/232,505364ccd33592763d599c91912d2e31ce55724d,apps/app/src/app/[locale]/(app)/(dashboard)/[o...,renamed,0,0,0,NaN
1027,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/src/jobs/tasks/deel/index.ts,renamed,0,0,0,NaN


In [26]:
first_commit_empty_files = human_commit_details_files[
    (human_commit_details_files['patch'].isna()) &
    (human_commit_details_files['filename'].str.startswith('.github/workflows'))&
    (human_commit_details_files['filename'].str.endswith(('.yaml', '.yml')))
]
first_commit_empty_files


,pr_url,sha,filename,status,additions,deletions,changes,patch
240,https://github.com/cloudwalk/stratus/pull/2079,ef0c32727b55ebdd956f539a3eb24c68ba08f2f6,.github/workflows/build-pgo.yml,renamed,0,0,0,NaN
750,https://github.com/roeniss/dhlottery-api/pull/150,71d8fa3a7c38b9b98598d07705eed29c471a4805,.github/workflows/lintFmtCheck.yml,renamed,0,0,0,NaN
751,https://github.com/roeniss/dhlottery-api/pull/152,7db6e990bb041488e598b45a489b6d3db7934535,.github/workflows/build-publish-release-note.yml,renamed,0,0,0,NaN
880,https://github.com/theopenco/llmgateway/pull/88,045a51ff1d799fdfc771441b5afd7b1d0d7e28a7,.github/workflows/images.yml,renamed,0,0,0,NaN
944,https://github.com/whitphx/stlite/pull/1375,cacdccfce20db6c10c075d920d7790cbbafb61de,.github/workflows/postbuild.yml,renamed,0,0,0,NaN
944,https://github.com/whitphx/stlite/pull/1375,cacdccfce20db6c10c075d920d7790cbbafb61de,.github/workflows/test-build.yml,renamed,0,0,0,NaN


In [27]:
human_eligible_prs_raw_valid = human_eligible_prs_raw.merge(first_commit_empty_files,left_on=['pr_url','first_commit_sha'],right_on=['pr_url','sha'],how='left_anti')
print(len(human_eligible_prs_raw_valid))
print(len(human_eligible_prs_raw))
human_eligible_prs_raw= human_eligible_prs_raw_valid
human_eligible_prs_raw[~human_eligible_prs_raw['pr_url'].isin(human_eligible_prs_raw_valid['pr_url'])]
print(len(human_eligible_prs_raw))

860
863
860


In [28]:
# save prs with non-empty first commits
human_pr = human_pr[human_pr['html_url'].isin(human_eligible_prs_raw['pr_url'])]
human_pr.to_csv('../datasets/processed/human_eligible_prs.csv')
human_pr

,html_url,first_commit_sha,state,locked,title,user.login,user.type,body,created_at,updated_at,closed_at,merged_at,merged,comments,review_comments,commits,additions,deletions,changed_files
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,closed,False,Switch scrypt to wallycore,3rdIteration,User,## Summary\n- prefer `wallycore.scrypt` in `li...,2025-07-30T01:21:27Z,2025-07-30T02:27:25Z,2025-07-30T02:27:22Z,2025-07-30T02:27:22Z,True,0,0,2,49,7,6
1,https://github.com/AMICI-dev/AMICI/pull/2825,c1ee0cf6cb2fc7e9699c89f2743720e6878833e9,closed,False,"Fix uninitialized values, update valgrind supp...",dweindl,User,Fixes current valgrind-reported issues.,2025-06-26T07:08:40Z,2025-09-24T10:00:09Z,2025-06-26T09:37:21Z,2025-06-26T09:37:21Z,True,1,0,1,31,7,3
2,https://github.com/AMICI-dev/AMICI/pull/2820,8a8fee87790a2393dbd31f7d763336d3e6dd57a8,closed,False,GHA: develop -> main,dweindl,User,Fix some missed references to the discontinued...,2025-06-25T12:54:06Z,2025-09-23T13:30:29Z,2025-06-25T13:19:58Z,2025-06-25T13:19:58Z,True,1,0,1,2,2,2
3,https://github.com/AMICI-dev/AMICI/pull/2819,809119384d0777c42c3465cfee21777d087f57e3,closed,False,GHA: Fix libsbml crashes,dweindl,User,"On Python3.11, to prevent crashes, don't use `...",2025-06-25T12:17:30Z,2025-09-23T13:30:09Z,2025-06-25T13:03:10Z,2025-06-25T13:03:10Z,True,1,0,1,5,0,1
4,https://github.com/AMICI-dev/AMICI/pull/2818,e8f4526b12823795103ee6cb472deeaec624caac,closed,False,GHA: build docs on ubuntu 24.04,dweindl,User,* Use Ubuntu 24.04 for documentation tests\r\n...,2025-06-24T06:28:47Z,2025-09-22T08:30:09Z,2025-06-24T08:06:10Z,2025-06-24T08:06:10Z,True,1,0,2,4,4,2
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
1023,https://github.com/trycompai/comp/pull/130,e467fb36abca8c853208d29b0e209af54c323ea9,closed,False,Auto translate english,Marfuen,User,\n\n<!-- This is an auto-generated comment: re...,2025-03-13T17:31:42Z,2025-03-13T17:34:01Z,2025-03-13T17:32:13Z,2025-03-13T17:32:13Z,True,2,0,1,42,0,1
1024,https://github.com/trycompai/comp/pull/118,c7c2ad2a547a12a9594525a1de2e680826820a0d,closed,False,point gh action to correct folder,Marfuen,User,\n\n<!-- This is an auto-generated comment: re...,2025-03-07T18:23:30Z,2025-03-07T18:24:53Z,2025-03-07T18:23:39Z,2025-03-07T18:23:39Z,True,2,0,1,1,0,1
1025,https://github.com/trycompai/comp/pull/116,b46d1388f624e489ead0046acab0a714e7ed8361,closed,False,refactor: update Trigger.dev configuration and...,Marfuen,User,- Update trigger configs to include new trigge...,2025-03-07T14:56:01Z,2025-03-07T14:57:37Z,2025-03-07T14:57:09Z,2025-03-07T14:57:08Z,True,2,0,1,89,44,6
1026,https://github.com/trycompai/comp/pull/113,70502f4a90a4d2012756f9695e3bffd7bd021bba,closed,False,fix deploy script,Marfuen,User,NaN,2025-03-06T20:08:07Z,2025-03-06T20:08:14Z,2025-03-06T20:08:12Z,2025-03-06T20:08:11Z,True,2,0,1,1,2,1


# Extract human commits

In [29]:
human_commits_df = human_eligible_prs_raw[['pr_url','commits','first_commit_sha']]
human_commits_exploded= human_commits_df.explode('commits')
print(f'total human prs {len(human_eligible_prs_raw)}')
print(f'total commits prs {len(human_commits_exploded)}')
human_commits_normalized = pd.json_normalize(human_commits_exploded['commits'])
print(f'human commits normalized {len(human_commits_normalized)}')
human_commits = pd.concat([human_commits_exploded['pr_url'],human_commits_normalized],axis=1)
print(f'human commits {len(human_commits)}')

# human_commits = human_commits.merge(empty_commits,on=['pr_url','sha'])
print(f'filtered human commits  {len(human_commits)}')
human_commits.to_csv('../datasets/processed/human_eligible_commits.csv', index=False )
human_commits.sort_values('pr_url')
# total human prs 632
# total commits prs 2364
# human commits normalized 2364
# human commits 2364


total human prs 860
total commits prs 4287
human commits normalized 4287
human commits 4287
filtered human commits  4287


,pr_url,sha,node_id,url,html_url,comments_url,parents,commit.author.name,commit.author.email,commit.author.date,...,committer.subscriptions_url,committer.organizations_url,committer.repos_url,committer.events_url,committer.received_events_url,committer.type,committer.user_view_type,committer.site_admin,author,committer
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,C_kwDOC8MeZ9oAKDY5MWM4YzFiMzJmMTIyNDRlYTM3OGVl...,https://api.github.com/repos/3rdIteration/btcr...,https://github.com/3rdIteration/btcrecover/com...,https://api.github.com/repos/3rdIteration/btcr...,[{'sha': '40f53d0ceb4f93e13fb3cddee9aab73569f4...,3rd Iteration,stevekr@gmail.com,2025-07-30T01:21:25Z,...,https://api.github.com/users/3rdIteration/subs...,https://api.github.com/users/3rdIteration/orgs,https://api.github.com/users/3rdIteration/repos,https://api.github.com/users/3rdIteration/even...,https://api.github.com/users/3rdIteration/rece...,User,public,False,NaN,NaN
0,https://github.com/3rdIteration/btcrecover/pul...,c1e87e12ae86042d23b323e6e38a37b8c911996f,C_kwDOC8MeZ9oAKGMxZTg3ZTEyYWU4NjA0MmQyM2IzMjNl...,https://api.github.com/repos/3rdIteration/btcr...,https://github.com/3rdIteration/btcrecover/com...,https://api.github.com/repos/3rdIteration/btcr...,[{'sha': '691c8c1b32f12244ea378ee0018e9f136ed4...,3rd Iteration,stevekr@gmail.com,2025-07-30T02:03:55Z,...,https://api.github.com/users/3rdIteration/subs...,https://api.github.com/users/3rdIteration/orgs,https://api.github.com/users/3rdIteration/repos,https://api.github.com/users/3rdIteration/even...,https://api.github.com/users/3rdIteration/rece...,User,public,False,NaN,NaN
14,https://github.com/567-labs/instructor/pull/1575,6bd8aa4a8eeaa2573f31abd99147ad513642d4fa,C_kwDOJvT6btoAKDZiZDhhYTRhOGVlYWEyNTczZjMxYWJk...,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/commit/...,https://api.github.com/repos/567-labs/instruct...,[{'sha': 'fe151f49267ea90c8a1f660df2c01e51520a...,Ivan Leo,ivanleomk@gmail.com,2025-06-02T23:15:39Z,...,https://api.github.com/users/ivanleomk/subscri...,https://api.github.com/users/ivanleomk/orgs,https://api.github.com/users/ivanleomk/repos,https://api.github.com/users/ivanleomk/events{...,https://api.github.com/users/ivanleomk/receive...,User,public,False,NaN,NaN
9,https://github.com/567-labs/instructor/pull/1675,23f1e916b052b3bcffb4d9f4dc15122d817ae9a2,C_kwDOJvT6btoAKDIzZjFlOTE2YjA1MmIzYmNmZmI0ZDlm...,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/commit/...,https://api.github.com/repos/567-labs/instruct...,[{'sha': 'f4dd2771edc619c1df4a8f6093b4e7dcfcfa...,jxnl,jason@jxnl.co,2025-07-07T23:54:50Z,...,https://api.github.com/users/jxnl/subscriptions,https://api.github.com/users/jxnl/orgs,https://api.github.com/users/jxnl/repos,https://api.github.com/users/jxnl/events{/priv...,https://api.github.com/users/jxnl/received_events,User,public,False,NaN,NaN
9,https://github.com/567-labs/instructor/pull/1675,00c1fef146a63b446ef5eaa1b62547af61070fca,C_kwDOJvT6btoAKDAwYzFmZWYxNDZhNjNiNDQ2ZWY1ZWFh...,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/commit/...,https://api.github.com/repos/567-labs/instruct...,[{'sha': '23f1e916b052b3bcffb4d9f4dc15122d817a...,jxnl,jason@jxnl.co,2025-07-08T00:07:10Z,...,https://api.github.com/users/jxnl/subscriptions,https://api.github.com/users/jxnl/orgs,https://api.github.com/users/jxnl/repos,https://api.github.com/users/jxnl/events{/priv...,https://api.github.com/users/jxnl/received_events,User,public,False,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
838,https://github.com/wvlet/wvlet/pull/972,11681cefdb0a994652b51b731695cc2796d2bb1c,C_kwDOMniuU9oAKDExNjgxY2VmZGIwYTk5NDY1MmI1MWI3...,https://api.github.com/repos/wvlet/wvlet/commi...,https://github.com/wvlet/wvlet/commit/11681cef...,https://api.github.com/repos/wvlet/wvlet/commi...,[{'sha': '1e3a8558b05075

# Extract human commit details

In [30]:
commit_details_raw = human_eligible_prs_raw[['pr_url','first_commit_sha','commit_details']]
commit_details_raw

commit_details_raw_exploded = commit_details_raw.explode(column=['commit_details'])
commit_details_normalized = pd.json_normalize(commit_details_raw_exploded['commit_details'])
commit_details_concat = pd.concat([commit_details_raw_exploded[['pr_url']],commit_details_normalized],axis=1)
commit_details_concat

commit_details_files_explode = commit_details_concat.explode('files').dropna(subset='files')
commit_details_files_normalized = pd.json_normalize(commit_details_files_explode['files'],max_level=0)
commit_details_files = pd.concat([commit_details_files_explode[['pr_url','sha']],commit_details_files_normalized[['filename','status','additions','deletions','changes','patch']]],axis=1)

commit_details_files.to_csv('../datasets/processed/human_eligible_commit_details.csv', index=False)
commit_details_files 

,pr_url,sha,filename,status,additions,deletions,changes,patch
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,.github/workflows/Weekly-Run-All-Tests-Full.yml,modified,1,1,2,"@@ -37,7 +37,7 @@ jobs:\n run: |\n ..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,.github/workflows/Weekly-Run-All-Tests_Base.yml,modified,1,1,2,"@@ -34,7 +34,7 @@ jobs:\n run: |\n ..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,.github/workflows/termux-tests.yml,modified,2,2,4,"@@ -49,7 +49,7 @@ jobs:\n run: chown -..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,docs/INSTALL.md,modified,9,1,10,"@@ -203,7 +203,15 @@ Locate your wallet type i..."
0,https://github.com/3rdIteration/btcrecover/pul...,691c8c1b32f12244ea378ee0018e9f136ed45755,lib/pylibscrypt/__init__.py,modified,29,2,31,"@@ -16,15 +16,42 @@\n \n __version__ = '2.0.0-..."
...,...,...,...,...,...,...,...,...
863,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,.github/workflows/trigger-tasks-deploy.yml,added,32,0,32,"@@ -0,0 +1,32 @@\n+name: Deploy to Trigger.dev..."
863,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/package.json,modified,3,2,5,"@@ -7,7 +7,8 @@\n ""build"": ""next build"",\n..."
863,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/src/jobs/tasks/deel/index.ts,renamed,0,0,0,NaN
863,https://github.com/trycompai/comp/pull/111,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,apps/app/src/jobs/tasks/deel/schedule.ts,renamed,0,0,0,NaN


# Extract human reviews

In [31]:
human_reviews_df = human_eligible_prs_raw[['pr_url','reviews']]
human_reviews_exploded= human_reviews_df.explode('reviews').dropna(subset=['reviews'])
human_reviews_normalized = pd.json_normalize(human_reviews_exploded['reviews'])

human_reviews = pd.concat([human_reviews_exploded['pr_url'],human_reviews_normalized],axis=1)
human_reviews.to_csv('../datasets/processed/human_eligible_reviews.csv', index=False)
print(f'human pr with review {len(human_reviews.groupby("pr_url").size())}')
human_reviews

human pr with review 495


,pr_url,id,node_id,body,state,html_url,pull_request_url,author_association,submitted_at,commit_id,...,user.subscriptions_url,user.organizations_url,user.repos_url,user.events_url,user.received_events_url,user.type,user.user_view_type,user.site_admin,_links.html.href,_links.pull_request.href
1,https://github.com/AMICI-dev/AMICI/pull/2825,2961244172,PRR_kwDOApp1-c6wgQAM,,APPROVED,https://github.com/AMICI-dev/AMICI/pull/2825#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...,MEMBER,2025-06-26T08:36:57Z,c1ee0cf6cb2fc7e9699c89f2743720e6878833e9,...,https://api.github.com/users/FFroehlich/subscr...,https://api.github.com/users/FFroehlich/orgs,https://api.github.com/users/FFroehlich/repos,https://api.github.com/users/FFroehlich/events...,https://api.github.com/users/FFroehlich/receiv...,User,public,False,https://github.com/AMICI-dev/AMICI/pull/2825#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...
3,https://github.com/AMICI-dev/AMICI/pull/2819,2958002688,PRR_kwDOApp1-c6wT4oA,,APPROVED,https://github.com/AMICI-dev/AMICI/pull/2819#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...,MEMBER,2025-06-25T12:41:41Z,809119384d0777c42c3465cfee21777d087f57e3,...,https://api.github.com/users/FFroehlich/subscr...,https://api.github.com/users/FFroehlich/orgs,https://api.github.com/users/FFroehlich/repos,https://api.github.com/users/FFroehlich/events...,https://api.github.com/users/FFroehlich/receiv...,User,public,False,https://github.com/AMICI-dev/AMICI/pull/2819#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...
4,https://github.com/AMICI-dev/AMICI/pull/2818,2952508465,PRR_kwDOApp1-c6v-7Qx,,APPROVED,https://github.com/AMICI-dev/AMICI/pull/2818#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...,MEMBER,2025-06-24T07:31:02Z,f87a463e0b29982add7e8be32bde4c2045682fa0,...,https://api.github.com/users/FFroehlich/subscr...,https://api.github.com/users/FFroehlich/orgs,https://api.github.com/users/FFroehlich/repos,https://api.github.com/users/FFroehlich/events...,https://api.github.com/users/FFroehlich/receiv...,User,public,False,https://github.com/AMICI-dev/AMICI/pull/2818#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...
5,https://github.com/AMICI-dev/AMICI/pull/2817,2952506865,PRR_kwDOApp1-c6v-63x,,APPROVED,https://github.com/AMICI-dev/AMICI/pull/2817#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...,MEMBER,2025-06-24T07:30:29Z,29de79bb5571885574f4bda014e49a3347190141,...,https://api.github.com/users/FFroehlich/subscr...,https://api.github.com/users/FFroehlich/orgs,https://api.github.com/users/FFroehlich/repos,https://api.github.com/users/FFroehlich/events...,https://api.github.com/users/FFroehlich/receiv...,User,public,False,https://github.com/AMICI-dev/AMICI/pull/2817#p...,https://api.github.com/repos/AMICI-dev/AMICI/p...
6,https://github.com/567-labs/instructor/pull/1699,3011944496,PRR_kwDOJvT6bs6zhqAw,> [!IMPORTANT]\n> **Looks good to me! :+1:**\...,COMMENTED,https://github.com/567-labs/instructor/pull/16...,https://api.github.com/repos/567-labs/instruct...,CONTRIBUTOR,2025-07-11T20:52:08Z,b4d2009757acd557409afb669d64450eb618d706,...,https://api.github.com/users/ellipsis-dev%5Bbo...,https://api.github.com/users/ellipsis-dev%5Bbo...,https://api.github.com/users/ellipsis-dev%5Bbo...,https://api.github.com/users/ellipsis-dev%5Bbo...,https://api.github.com/users/ellipsis-dev%5Bbo...,Bot,public,False,https://github.com/567-labs/instructor/pull/16...,https://api.github.com/repos/567-labs/instruct...
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
853,https://github.com/trycompai/comp/pull/314,2747536481,PRR_kwDONq3Itc6jxBRh,**Actionable comments posted: 0**\n\n<details>...,COMMENTED,https://github.com/trycompai/comp/pull/314#pul...,https://api.github.com/repos/trycompai/comp/pu...,NONE,2025-04-07T17:12:19Z,b3c7101717de2e3dcba58e5c92cee1b44b22e408,...,https://api.github.com/users/coderabbitai%5Bbo...,https://api.github.com/users/coderabbitai%5Bbo...,https://api.github.com/users/coderabbit

# Extract Human inline review

In [32]:
human_inline_reviews_df = human_eligible_prs_raw[['pr_url','inline_review_comments']]
human_inline_reviews_exploded = human_inline_reviews_df.explode('inline_review_comments').dropna()
human_inline_reviews_normalized = pd.json_normalize(human_inline_reviews_exploded['inline_review_comments'])

human_inline_reviews = pd.concat([human_inline_reviews_exploded['pr_url'], human_inline_reviews_normalized], axis=1)
human_inline_reviews.to_csv('../datasets/processed/human_eligible_inline_reviews.csv', index=False)
human_inline_reviews.sort_values('pr_url')

,pr_url,url,pull_request_review_id,id,node_id,diff_hunk,path,commit_id,original_commit_id,body,...,reactions.total_count,reactions.+1,reactions.-1,reactions.laugh,reactions.hooray,reactions.confused,reactions.heart,reactions.rocket,reactions.eyes,in_reply_to_id
7,https://github.com/AMICI-dev/AMICI/pull/2839,https://api.github.com/repos/AMICI-dev/AMICI/p...,2962731755,2169452826,PRRC_kwDOApp1-c6BTzka,"@@ -0,0 +1,34 @@\n+name: Conda installation\n+...",.github/workflows/test_conda_install.yml,c6f2e1c5f931aabb8174c0f76d47afdd8b31ff31,f88a2a27bf8987e57a6a42cd2e6514d21a89e115,I think amici still needs to be installed via ...,...,0,0,0,0,0,0,0,0,0,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,https://api.github.com/repos/AMICI-dev/AMICI/p...,2977679598,2179062335,PRRC_kwDOApp1-c6B4do_,"@@ -0,0 +1,35 @@\n+name: Conda installation\n+...",.github/workflows/test_conda_install.yml,c6f2e1c5f931aabb8174c0f76d47afdd8b31ff31,d2f1cf8b36f43a1e345897613256378d0991d582,```suggestion\r\n pip install -v git+...,...,0,0,0,0,0,0,0,0,0,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,https://api.github.com/repos/AMICI-dev/AMICI/p...,3441176165,2508983677,PRRC_kwDOApp1-c6VjA19,"@@ -0,0 +1,40 @@\n+name: Conda installation\n+...",.github/workflows/test_conda_install.yml,6a43cb947899b6bdd7e57322feccb4bb7c4ae983,a8bfe6e90c6c1a4cbb48585a8f6efff57c76388b,Let's also build a model extension and run a s...,...,0,0,0,0,0,0,0,0,0,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,https://api.github.com/repos/AMICI-dev/AMICI/p...,3441176165,2508987681,PRRC_kwDOApp1-c6VjB0h,"@@ -6,6 +6,11 @@ cmake_minimum_required(VERSIO...",CMakeLists.txt,6a43cb947899b6bdd7e57322feccb4bb7c4ae983,a8bfe6e90c6c1a4cbb48585a8f6efff57c76388b,Do we need this and the change below? Last tim...,...,0,0,0,0,0,0,0,0,0,NaN
7,https://github.com/AMICI-dev/AMICI/pull/2839,https://api.github.com/repos/AMICI-dev/AMICI/p...,3442399131,2509891871,PRRC_kwDOApp1-c6Vmekf,"@@ -238,7 +243,8 @@ add_dependencies(${PROJECT...",CMakeLists.txt,a8bfe6e90c6c1a4cbb48585a8f6efff57c76388b,a8bfe6e90c6c1a4cbb48585a8f6efff57c76388b,```suggestion\r\n ...,...,0,0,0,0,0,0,0,0,0,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
789,https://github.com/whitphx/stlite/pull/1463,https://api.github.com/repos/whitphx/stlite/pu...,2797570921,2062569171,PRRC_kwDOHVVJhM568E7T,"@@ -216,21 +224,29 @@\n registry-url: ...",.github/workflows/postbuild.yml,a83fc7c385bb2f029731c7b5641f144864026b11,a83fc7c385bb2f029731c7b5641f144864026b11,## Artifact poisoning\n\nPotential artifact po...,...,0,0,0,0,0,0,0,0,0,NaN
831,https://github.com/wvlet/wvlet/pull/1019,https://api.github.com/repos/wvlet/wvlet/pulls...,2948085168,2160248351,PRRC_kwDOMniuU86AwsYf,"@@ -258,4 +258,16 @@ For error reporting, use ...",CLAUDE.md,8735c570f4a8281389a30a218737d5e9e2dfdc4a,93c869a0626870c58f9e2fa03018c80a32bc42e1,![medium](https://www.gstatic.com/codereviewag...,...,0,0,0,0,0,0,0,0,0,NaN
835,https://github.com/yamadashy/repomix/pull/604,https://api.github.com/repos/yamadashy/repomix...,2869540940,2108141999,PRRC_kwDOMVwZR859p7Gv,"@@ -0,0 +1,37 @@\n+name: Claude Code\n+\n+on:\...",.github/workflows/claude.yml,44f0d05ae803cc17aceede6aa1d7b8a6981e4830,44f0d05ae803cc17aceede6aa1d7b8a6981e4830,The workflow only has read permissions for iss...,...,0,0,0,0,0,0,0,0,0,NaN
834,https://github.com/yamadashy/repomix/pull/605,https://api.github.com/repos/yamadashy/repomix...,2869565425,2108159491,PRRC_kwDOMVwZR859p_YD,"@@ -0,0 +1,37 @@\n+name: Claude Code\n+\n+on:\...",.github/workflows/claude.yml,87f9199e08d093204c71bc77aefec0f7bf4ab43b,87f9199e08d093204c71bc77aefec0f7bf4ab43b,Using a shallow checkout (fetch-depth: 1) can ...,...,0,0,0,0,0,0,0,0,0,NaN


# Extract Human comments

In [33]:
human_comments_df = human_eligible_prs_raw[['pr_url', 'comments']]
human_comments_exploded = human_comments_df.explode('comments').dropna()
human_comments_normalized = pd.json_normalize(human_comments_exploded['comments'])
human_comments = pd.concat([human_comments_exploded['pr_url'], human_comments_normalized], axis=1)
human_comments.to_csv('../datasets/processed/human_eligible_comments.csv', index=False)
human_comments.sort_values('pr_url')

,pr_url,url,html_url,issue_url,id,node_id,created_at,updated_at,body,author_association,...,performed_via_github_app.permissions.organization_plan,performed_via_github_app.permissions.organization_projects,performed_via_github_app.permissions.organization_self_hosted_runners,performed_via_github_app.permissions.organization_user_blocking,performed_via_github_app.permissions.plan,performed_via_github_app.permissions.repository_advisories,performed_via_github_app.permissions.repository_custom_properties,performed_via_github_app.permissions.secret_scanning_alerts,performed_via_github_app.permissions.team_discussions,performed_via_github_app.permissions.secrets
14,https://github.com/567-labs/instructor/pull/1575,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/pull/15...,https://api.github.com/repos/567-labs/instruct...,2932853421,IC_kwDOJvT6bs6uz8qt,2025-06-02T23:22:19Z,2025-06-02T23:24:12Z,"## Deploying with &nbsp;<a href=""https://worke...",NONE,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
14,https://github.com/567-labs/instructor/pull/1575,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/pull/15...,https://api.github.com/repos/567-labs/instruct...,2932860250,IC_kwDOJvT6bs6uz-Va,2025-06-02T23:26:23Z,2025-06-02T23:26:23Z,@claude can you help me to add in a fix so tha...,CONTRIBUTOR,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
8,https://github.com/567-labs/instructor/pull/1688,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/pull/16...,https://api.github.com/repos/567-labs/instruct...,3057961142,IC_kwDOJvT6bs62RMi2,2025-07-10T15:35:10Z,2025-07-10T15:36:46Z,**Claude finished @jxnl's task** —— [View job]...,CONTRIBUTOR,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
6,https://github.com/567-labs/instructor/pull/1699,https://api.github.com/repos/567-labs/instruct...,https://github.com/567-labs/instructor/pull/16...,https://api.github.com/repos/567-labs/instruct...,3063786125,IC_kwDOJvT6bs62naqN,2025-07-11T20:51:49Z,2025-07-11T20:53:07Z,**Claude finished @jxnl's task** —— [View job]...,CONTRIBUTOR,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
13,https://github.com/AMICI-dev/AMICI/pull/2772,https://api.github.com/repos/AMICI-dev/AMICI/i...,https://github.com/AMICI-dev/AMICI/pull/2772#i...,https://api.github.com/repos/AMICI-dev/AMICI/i...,2950513721,IC_kwDOApp1-c6v3UQ5,2025-06-06T19:39:02Z,2025-09-29T12:00:12Z,## [Codecov](https://app.codecov.io/gh/AMICI-d...,NONE,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
834,https://github.com/yamadashy/repomix/pull/605,https://api.github.com/repos/yamadashy/repomix...,https://github.com/yamadashy/repomix/pull/605#...,https://api.github.com/repos/yamadashy/repomix...,2911090206,IC_kwDOMVwZR86tg7Ye,2025-05-27T04:52:49Z,2025-05-27T04:52:49Z,"## Deploying repomix with &nbsp;<a href=""https...",NONE,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
833,https://github.com/yamadashy/repomix/pull/606,https://api.github.com/repos/yamadashy/repomix...,https://github.com/yamadashy/repomix/pull/606#...,https://api.github.com/repos/yamadashy/repomix...,2912395067,IC_kwDOMVwZR86tl587,2025-05-27T12:48:29Z,2025-05-27T12:48:29Z,> [!NOTE]\n> Gemini is unable to generate a su...,CONTRIBUTOR,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
833,https://github.com/yamadashy/repomix/pull/606,https://api.github.com/repos/yamadashy/repomix...,https://github.com/yamadashy/repomix/pull/606#...,https://api.github.com/repos/yamadashy/repomix...,2912397141,IC_kwDOMVwZR86tl6dV,2025-05-27T12:49:14Z,2025-05-27T12:57:01Z,## [Codecov](https://app.codecov.io/gh/yamadas...,NONE,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
833,https://github.com/yamadashy/repomix/pull/606,https://api.github.com/repos/yamadashy/repomix...,https://github.com/yamadashy/repomix/pull/606#...,https://api.github.com/repos/yamadashy/repomix...,2912400105,IC_kwDOMVwZR86tl7Lp,2

In [34]:
human_commit_details_files.columns

Index(['pr_url', 'sha', 'filename', 'status', 'additions', 'deletions',
       'changes', 'patch'],
      dtype='str')

In [35]:
dict(human_commits[human_commits['sha']=='72384007ea789b5756b9bae7781510b549bf839e']['url'])

{}

# Eligible builds

## Get raw data

In [36]:
builds_raw = pd.read_json('../datasets/raw/eligible_commits_check_runs.jsonl', lines=True)
human_build_raw = builds_raw[builds_raw['pr_type']=='human']
human_build_raw

,commit,pr,pr_type,check_runs
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,"{'total_count': 38, 'check_runs': [{'id': 4699..."
2834,c1e87e12ae86042d23b323e6e38a37b8c911996f,https://github.com/3rdIteration/btcrecover/pul...,human,"{'total_count': 38, 'check_runs': [{'id': 4699..."
2835,c1ee0cf6cb2fc7e9699c89f2743720e6878833e9,https://github.com/AMICI-dev/AMICI/pull/2825,human,"{'total_count': 33, 'check_runs': [{'id': 4482..."
2836,8a8fee87790a2393dbd31f7d763336d3e6dd57a8,https://github.com/AMICI-dev/AMICI/pull/2820,human,"{'total_count': 23, 'check_runs': [{'id': 4476..."
2837,809119384d0777c42c3465cfee21777d087f57e3,https://github.com/AMICI-dev/AMICI/pull/2819,human,"{'total_count': 29, 'check_runs': [{'id': 4476..."
...,...,...,...,...
7160,e467fb36abca8c853208d29b0e209af54c323ea9,https://github.com/trycompai/comp/pull/130,human,"{'total_count': 11, 'check_runs': [{'id': 3899..."
7161,c7c2ad2a547a12a9594525a1de2e680826820a0d,https://github.com/trycompai/comp/pull/118,human,"{'total_count': 11, 'check_runs': [{'id': 3858..."
7162,b46d1388f624e489ead0046acab0a714e7ed8361,https://github.com/trycompai/comp/pull/116,human,"{'total_count': 12, 'check_runs': [{'id': 3858..."
7163,70502f4a90a4d2012756f9695e3bffd7bd021bba,https://github.com/trycompai/comp/pull/113,human,"{'total_count': 12, 'check_runs': [{'id': 3858..."


## Filter builds , eligible commits only

### Check eligible commits in fetched build commits

In [37]:
print(f"eligible commits {len(human_commits)}")
print(f"fetched build commits {len(human_build_raw)}")
print(f"fetched eligible builds commits {len(human_build_raw[human_build_raw['commit'].isin(human_commits['sha'])])}")

eligible commits 4287
fetched build commits 4332
fetched eligible builds commits 4287


### Filter build commits by eligible commits

In [38]:
eligible_builds_raw = human_build_raw[human_build_raw['commit'].isin(human_commits['sha'])]
print(f"eligible builds raw {len(eligible_builds_raw)}")
eligible_builds_raw

eligible builds raw 4287


,commit,pr,pr_type,check_runs
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,"{'total_count': 38, 'check_runs': [{'id': 4699..."
2834,c1e87e12ae86042d23b323e6e38a37b8c911996f,https://github.com/3rdIteration/btcrecover/pul...,human,"{'total_count': 38, 'check_runs': [{'id': 4699..."
2835,c1ee0cf6cb2fc7e9699c89f2743720e6878833e9,https://github.com/AMICI-dev/AMICI/pull/2825,human,"{'total_count': 33, 'check_runs': [{'id': 4482..."
2836,8a8fee87790a2393dbd31f7d763336d3e6dd57a8,https://github.com/AMICI-dev/AMICI/pull/2820,human,"{'total_count': 23, 'check_runs': [{'id': 4476..."
2837,809119384d0777c42c3465cfee21777d087f57e3,https://github.com/AMICI-dev/AMICI/pull/2819,human,"{'total_count': 29, 'check_runs': [{'id': 4476..."
...,...,...,...,...
7160,e467fb36abca8c853208d29b0e209af54c323ea9,https://github.com/trycompai/comp/pull/130,human,"{'total_count': 11, 'check_runs': [{'id': 3899..."
7161,c7c2ad2a547a12a9594525a1de2e680826820a0d,https://github.com/trycompai/comp/pull/118,human,"{'total_count': 11, 'check_runs': [{'id': 3858..."
7162,b46d1388f624e489ead0046acab0a714e7ed8361,https://github.com/trycompai/comp/pull/116,human,"{'total_count': 12, 'check_runs': [{'id': 3858..."
7163,70502f4a90a4d2012756f9695e3bffd7bd021bba,https://github.com/trycompai/comp/pull/113,human,"{'total_count': 12, 'check_runs': [{'id': 3858..."


## Extract Build data

In [39]:
eligible_builds_raw_normalized = pd.json_normalize(eligible_builds_raw['check_runs'])
eligible_builds_raw_normalized = pd.concat([eligible_builds_raw.drop(columns=['check_runs']), eligible_builds_raw_normalized], axis=1)

eligible_builds_raw_exploded = eligible_builds_raw_normalized.explode('check_runs')
eligible_builds_raw_exploded['check_runs'] = eligible_builds_raw_exploded['check_runs'].apply(lambda x: x if isinstance(x, dict) else {})
eligible_builds_normalized = pd.json_normalize(eligible_builds_raw_exploded['check_runs'])
eligible_builds = pd.concat([eligible_builds_raw_exploded.drop(columns=['check_runs']), eligible_builds_normalized], axis=1)
eligible_builds

,commit,pr,pr_type,total_count,id,name,node_id,head_sha,external_id,url,...,deployment.id,deployment.node_id,deployment.task,deployment.original_environment,deployment.environment,deployment.description,deployment.created_at,deployment.updated_at,deployment.statuses_url,deployment.repository_url
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (ubuntu-24.04, 3.14.0-rc.1)",CR_kwDOC8MeZ88AAAAK8RRYQg,691c8c1b32f12244ea378ee0018e9f136ed45755,351e76ee-98e3-5e89-b86c-cd9cec3fba71,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (ubuntu-24.04, 3.13)",CR_kwDOC8MeZ88AAAAK8RRYPg,691c8c1b32f12244ea378ee0018e9f136ed45755,10237ecb-f386-5925-ab97-af35da76b1ce,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (macos-latest, 3.11)",CR_kwDOC8MeZ88AAAAK8RRYDw,691c8c1b32f12244ea378ee0018e9f136ed45755,84c130b7-cb62-5715-8573-822d013ca060,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (macos-latest, 3.13)",CR_kwDOC8MeZ88AAAAK8RRYDA,691c8c1b32f12244ea378ee0018e9f136ed45755,3b8e5dff-f852-5874-998a-56221c477774,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (macos-latest, 3.12)",CR_kwDOC8MeZ88AAAAK8RRYCw,691c8c1b32f12244ea378ee0018e9f136ed45755,8784acae-cca1-5a9a-bfd9-26e770df23d8,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
7164,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,https://github.com/trycompai/comp/pull/111,human,13,3.833490e+10,Mintlify Deployment,CR_kwDONq3Itc8AAAAI7PAy9g,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,,https://api.github.com/repos/trycompai/comp/ch...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
7164,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,https://github.com/trycompai/comp/pull/111,human,13,3.833490e+10,Vercel Preview Comments,CR_kwDONq3Itc8AAAAI7PAytQ,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,,https://api.github.com/repos/trycompai/comp/ch...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
7164,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,https://github.com/trycompai/comp/pull/111,human,13,3.833490e+10,Vercel Preview Comments,CR_kwDONq3Itc8AAAAI7PAwpg,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,,https://api.github.com/repos/trycompai/comp/ch...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
7164,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,https://github.com/trycompai/comp/pull/111,human,13,3.833490e+10,Vercel Preview Comments,CR_kwDONq3Itc8AAAAI7PAtyA,5acbbe47e7c47e6bf888c4b54e733b4f7d0cfdc4,,https://api.github.com/repos/trycompai/comp/ch...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN


In [40]:
dict(eligible_builds['pr'].head(1))
eligible_builds[eligible_builds['pr']=='https://github.com/3rdIteration/btcrecover/pull/616']

,commit,pr,pr_type,total_count,id,name,node_id,head_sha,external_id,url,...,deployment.id,deployment.node_id,deployment.task,deployment.original_environment,deployment.environment,deployment.description,deployment.created_at,deployment.updated_at,deployment.statuses_url,deployment.repository_url
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (ubuntu-24.04, 3.14.0-rc.1)",CR_kwDOC8MeZ88AAAAK8RRYQg,691c8c1b32f12244ea378ee0018e9f136ed45755,351e76ee-98e3-5e89-b86c-cd9cec3fba71,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (ubuntu-24.04, 3.13)",CR_kwDOC8MeZ88AAAAK8RRYPg,691c8c1b32f12244ea378ee0018e9f136ed45755,10237ecb-f386-5925-ab97-af35da76b1ce,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (macos-latest, 3.11)",CR_kwDOC8MeZ88AAAAK8RRYDw,691c8c1b32f12244ea378ee0018e9f136ed45755,84c130b7-cb62-5715-8573-822d013ca060,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (macos-latest, 3.13)",CR_kwDOC8MeZ88AAAAK8RRYDA,691c8c1b32f12244ea378ee0018e9f136ed45755,3b8e5dff-f852-5874-998a-56221c477774,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2833,691c8c1b32f12244ea378ee0018e9f136ed45755,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699432e+10,"build (macos-latest, 3.12)",CR_kwDOC8MeZ88AAAAK8RRYCw,691c8c1b32f12244ea378ee0018e9f136ed45755,8784acae-cca1-5a9a-bfd9-26e770df23d8,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
2834,c1e87e12ae86042d23b323e6e38a37b8c911996f,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699585e+10,"build (ubuntu-24.04, 3.9)",CR_kwDOC8MeZ88AAAAK8SvI2Q,c1e87e12ae86042d23b323e6e38a37b8c911996f,19513d03-7ea3-5bcf-b6bf-3ebdb085e864,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2834,c1e87e12ae86042d23b323e6e38a37b8c911996f,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699585e+10,"Termux Base (ubuntu-24.04-arm, aarch64)",CR_kwDOC8MeZ88AAAAK8SvIsg,c1e87e12ae86042d23b323e6e38a37b8c911996f,fba6d180-588a-57e0-85dc-64985b5d07b9,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2834,c1e87e12ae86042d23b323e6e38a37b8c911996f,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699585e+10,"Termux Full (ubuntu-24.04-arm, aarch64)",CR_kwDOC8MeZ88AAAAK8SvIsQ,c1e87e12ae86042d23b323e6e38a37b8c911996f,a10dd17d-c7e3-5916-9d19-f6ac19b21018,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
2834,c1e87e12ae86042d23b323e6e38a37b8c911996f,https://github.com/3rdIteration/btcrecover/pul...,human,38,4.699585e+10,pocl,CR_kwDOC8MeZ88AAAAK8SvIoQ,c1e87e12ae86042d23b323e6e38a37b8c911996f,b69a0c5b-b39f-55b3-b9ef-494c12cad47e,https://api.github.com/repos/3rdIteration/btcr...,...,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN,NaN
